In [ ]:
import pandas as pd
from sklearn.feature_extraction.text import TfidfVectorizer
from sklearn.metrics.pairwise import cosine_similarity
import re

ModuleNotFoundError: No module named 'pandas'

: 

In [ ]:
df = pd.read_csv(r"C:\Users\Shreyansh\ML\Projects\Game Reccomendation\final_augmented_games_dataset.csv", encoding="utf-8")
df['genres'] = df['genres'].fillna('')
df['categories'] = df['categories'].fillna('')
df['steamspy_tags'] = df['steamspy_tags'].fillna('')
df['developer'] = df['developer'].fillna('')

In [ ]:
def clean_developer_name(dev_string):
    return ';'.join([d.replace(' ', '') for d in dev_string.split(';')])
df['developer_tags'] = df['developer'].apply(clean_developer_name)
df['metadata'] = df['genres'] + ';' + df['categories'] + ';' + df['steamspy_tags'] + ';' + df['developer_tags']

In [ ]:
len(df)
df.tail()

,appid,name,release_date,english,developer,publisher,platforms,required_age,categories,genres,steamspy_tags,achievements,positive_ratings,negative_ratings,average_playtime,median_playtime,owners,price,developer_tags,metadata
26127,1069469.0,Hogwarts Legacy,10-02-2023,1,Avalanche Software,Warner Bros. Games,windows,13,Single-player,Action;Adventure;RPG,Fantasy;Magic;Open World,46,717289.0,17851.0,18625.0,9312.0,19787000-30705954,69.95,AvalancheSoftware,Action;Adventure;RPG;Single-player;Fantasy;Mag...
26128,1069475.0,Baldur's Gate 3 Edition 4,03-08-2023,1,Larian Studios,Larian Studios,windows;mac,16,Single-player;Online Co-op,RPG;Adventure,D&D;Story Rich;Choices Matter,54,1644690.0,24207.0,36457.0,18228.0,17298588-43183674,28.48,LarianStudios,RPG;Adventure;Single-player;Online Co-op;D&D;S...
26129,1069481.0,God of War Edition 4,14-01-2019,1,Santa Monica Studio,PlayStation PC LLC,windows,18,Single-player;Steam Cloud,Action;Adventure,Action;Story Rich;Mythology,37,1915089.0,8466.0,64345.0,32172.0,5884538-48058797,50.50,SantaMonicaStudio,Action;Adventure;Single-player;Steam Cloud;Act...
26130,NaN,God of War Ragnarok,09-11-2022,1,Santa Monica Studio,Sony Interactive Entertainment,PS4;PS5;Windows,17,Single-player;Story Rich;Third Person,Action;Adventure,Mythology;Action;Adventure;Story Rich;Third Pe...,0,NaN,NaN,NaN,NaN,NaN,69.99,SantaMonicaStudio,Action;Adventure;Single-player;Story Rich;Thir...
26131,NaN,Horizon Zero Dawn,28-02-2017,1,Guerrilla Games,Sony Interactive Entertainment,PS4;Windows,13,Single-player;Open World;Story Rich,Action;RPG,Open World;Story Rich;RPG;Action,0,NaN,NaN,NaN,NaN,NaN,49.99,GuerrillaGames,Action;RPG;Single-player;Open World;Story Rich...


In [ ]:
for i in range(len(df)):
    # Remove unwanted characters, keeping only letters and :
    games = re.sub('[^a-zA-Z:]', ' ', df['name'][i])
    
    # Collapse multiple spaces into one
    games = re.sub('\s+', ' ', games)
    
    # Remove spaces from start and end
    df['name'][i] = games.strip()

# Final safety strip for entire column
df['name'] = df['name'].str.strip()



<>:6: SyntaxWarning: invalid escape sequence '\s'
<>:6: SyntaxWarning: invalid escape sequence '\s'
C:\Users\Shreyansh\AppData\Local\Temp\ipykernel_4456\2877372331.py:6: SyntaxWarning: invalid escape sequence '\s'
  games = re.sub('\s+', ' ', games)
C:\Users\Shreyansh\AppData\Local\Temp\ipykernel_4456\2877372331.py:9: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  df['name'][i] = games.strip()
C:\Users\Shreyansh\AppData\Local\Temp\ipykernel_4456\2877372331.py:9: SettingWithCopyWarning: 
A value is trying to be set on a copy of a slice from a DataFrame

See the caveats in the documentation: https://pandas.pydata.org/pandas-docs/stable/user_guide/indexing.html#returning-a-view-versus-a-copy
  df['name'][i] = games.strip()
C:\Users\Shreyansh\AppData\Local\Temp\ipykernel_4456\2877372331.py:9: SettingWithCop

In [ ]:
tfidf_vectorizer = TfidfVectorizer(
    tokenizer=lambda x: list(set(x.lower().split(';'))), # Use set() to remove duplicate tags for a game
    lowercase=False # We already handled lowercase in the lambda
)
tfidf_matrix = tfidf_vectorizer.fit_transform(df['metadata'])
cosine_sim = cosine_similarity(tfidf_matrix)


c:\Users\Shreyansh\anaconda3\envs\sekiro\Lib\site-packages\sklearn\feature_extraction\text.py:521: UserWarning: The parameter 'token_pattern' will not be used since 'tokenizer' is not None'
  warnings.warn(


In [ ]:
def get_best_match(partial_name):
    matches = df[df['name'].str.contains(partial_name, case=False, na=False)]
    if matches.empty:
        return None
    return matches.iloc[0]['name']  # Return the first match


In [ ]:
def recommend_game(title, top_n=5):
    best_match = get_best_match(title)
    if not best_match:
        return f"No game found for input: '{title}'"
    print("Giving recommendations for :",best_match)
    index = df[df['name'] == best_match].index[0]
    
    similarity_scores = list(enumerate(cosine_sim[index]))
    similarity_scores = sorted(similarity_scores, key=lambda x: x[1], reverse=True)
    top_similar_games = similarity_scores[1:top_n+1]
    game_indices = [i[0] for i in top_similar_games]
    return df['name'].iloc[game_indices].tolist()


In [ ]:
print(recommend_game("dark souls"))

Giving recommendations for : DARK SOULS II
['DARK SOULS II: Scholar of the First Sin', 'DARK SOULS III', 'DARK SOULS : REMASTERED', 'INFERNO CLIMBER', 'Tormentum Dark Sorrow']
